## Cálculo de población por zona

Esta notebook calcula la población estimada de cada zona de la zonificación A15 a partir de los microdatos del Censo 2023 y los segmentos censales georreferenciados.

El procedimiento consiste en:

1. Calcular la población de cada segmento censal a partir del ponderador W
2. Asignar cada segmento a una zona de la zonificación
3. Sumar la población de los segmentos pertenecientes a cada zona
4. Guardar el resultado en un nuevo GeoPackage

In [1]:
import pandas as pd
import geopandas as gpd
import folium
import branca.colormap as cm
pd.set_option("display.max_columns", None)

A continuación, se cargan los microdatos del censo, los segmentos censales y el archivo de zonificación a15.gpkg. 

Se unifica el sistema de coordenadas de los segmentos censales y la zonificación, y se excluyen del cálculo los registros correspondientes a personas en situación de calle (SIT_CALLE = 1).

Además, se construye el código único de segmento (CODSEG) a partir del departamento, sección y segmento, siguiendo la estructura definida en la documentación de los microdatos.

Luego, se suma el ponderador W para todas las personas pertenecientes a cada segmento. El resultado representa la población estimada asociada a cada segmento censal.

In [ ]:
censo = pd.read_csv("../data/personas_ext_07_2026.csv", encoding='latin-1')
segmentos = gpd.read_file("../data/sg_23_pg.gpkg")
zonificacion = gpd.read_file("../data/a15.gpkg")

segmentos = segmentos.to_crs(zonificacion.crs)
censo = censo.loc[censo["SIT_CALLE"] != 1].copy()

# Crear CODSEG en los microdatos. Según la documentación: Departamento = 2 caracteres, Sección = 2 caracteres , Segmento = 3 caracteres

censo["CODSEG"] = (censo["DEPARTAMENTO"].astype(str).str.zfill(2) + censo["SECCION"].astype(str).str.zfill(2) + censo["SEGMENTO"].astype(str).str.zfill(3))

pop_por_segmento = (censo.groupby("CODSEG")["W"].sum().reset_index(name="POBLACION")) # calculo la población por segmento, sumando el ponderador W de todas las personas pertenecientes a cada segmento

segmentos = segmentos.merge(pop_por_segmento, on="CODSEG", how="left") # uno la población al geopackage 

Para asignar cada segmento a una única zona, se utiliza un punto representativo de su geometría.

Luego, se realiza un spatial join entre estos puntos y los polígonos de la zonificación A15. De esta forma, cada segmento queda asociado a la zona en la que se encuentra su punto representativo.

Se conservan únicamente los segmentos que se encuentran dentro del área de interés.

In [3]:
segmentos_puntos = segmentos.copy()

segmentos_puntos["geometry"] = (segmentos.geometry.representative_point()) # punto representatrivo para que cada segmento sea asignado a una única zona

segmentos_zona = gpd.sjoin(segmentos_puntos, zonificacion, predicate="within", how="left") # asignar cada segmento a un polígono de la zonificación

segmentos_dentro = segmentos_zona[segmentos_zona["index_right"].notna()].copy() # me quedo con sólo los segmentos de la AOI

Se realizan algunos controles para verificar la asignación de los segmentos y la disponibilidad de datos de población.

En particular, se revisa:

- si algún segmento fue asignado a más de una zona;
- cuántos segmentos se encuentran dentro del AOI;
- cuántos tienen población disponible;
- cuántos no tienen un valor de población.

In [4]:
duplicados = segmentos_dentro.index.duplicated().sum()

print("Segmentos asignados a más de una zona:",duplicados)

Segmentos asignados a más de una zona: 0


In [5]:
print("Segmentos dentro del AOI:", len(segmentos_dentro))

print("Segmentos con POBLACION:", segmentos_dentro["POBLACION"].notna().sum())

print("Segmentos con NaN en POBLACION:", segmentos_dentro["POBLACION"].isna().sum())   # hay 90 segmentos censales que no tienen valor ponderado de poblacion

Segmentos dentro del AOI: 3156
Segmentos con POBLACION: 3066
Segmentos con NaN en POBLACION: 90


In [6]:
codseg_nan = segmentos_dentro.loc[segmentos_dentro["POBLACION"].isna(), "CODSEG"]
codseg_nan

15      0809005
26      0906002
30      0118101
147     1404009
171     1606607
         ...   
4391    0504205
4500    1001630
4506    1410410
4516    0908105
4537    1006115
Name: CODSEG, Length: 90, dtype: object

La población de cada zona se obtiene sumando la población estimada de todos los segmentos asignados a ella.

Las zonas para las que no existe ningún segmento con población disponible quedan con valor NaN.

El resultado se incorpora a la capa de zonificación en la columna poblacion.

In [7]:
poblacion_zona = segmentos_dentro.groupby("index_right")["POBLACION"].sum(min_count=1)
zonificacion["POBLACION"] = zonificacion.index.map(poblacion_zona)

Finalmente, la zonificación con la población calculada se guarda como un nuevo GeoPackage.

In [ ]:
zonificacion["poblacion"] = zonificacion["POBLACION"].round().astype("Int64")  # Int64 admite NaN
zonificacion = zonificacion.drop(columns="POBLACION")
zonificacion.to_file("../output/a15-con-poblacion.gpkg", driver="GPKG")
zonificacion

,poligono_id,tipo_zona,depto_codigo,depto_nombre,seccion_codigo,geometry,poblacion
0,0,Core,03,CANELONES,0337,"POLYGON ((588449.643 6139996.561, 588432.458 6...",6514
1,1,Core,03,CANELONES,0337,"POLYGON ((587249.329 6141461.688, 587219.907 6...",5828
2,2,Core,03,CANELONES,0337,"POLYGON ((586351.435 6142346.669, 586337.956 6...",7965
3,3,Core,03,CANELONES,0337,"POLYGON ((591015.059 6141666.17, 590971.979 61...",4758
4,4,Core,03,CANELONES,0337,"POLYGON ((590499.401 6142652.304, 590556.742 6...",2667
...,...,...,...,...,...,...,...
565,565,Core,01,MONTEVIDEO,0111,"POLYGON ((585758.954 6150287.081, 585754.208 6...",3251
566,566,Core,01,MONTEVIDEO,0199,"POLYGON ((585698.543 6150148.085, 585722.518 6...",6631
567,567,Core,01,MONTEVIDEO,0109,"POLYGON ((571937.833 6152930.841, 571657.708 6...",472
568,568,Core,01,MONTEVIDEO,0117,"POLYGON ((575854.792 6154660.466, 575854.925 6...",1044


In [11]:
zonas_mapa = zonificacion.to_crs(epsg=4326).copy()
zonas_mapa["sin_dato"] = zonas_mapa["poblacion"].isna()

print("Zonas sin dato:", zonas_mapa["sin_dato"].sum(), "de", len(zonas_mapa))

# los segmentos sin match, para verlos por encima de las zonas
segmentos_nan = segmentos_dentro.loc[segmentos_dentro["POBLACION"].isna(), "CODSEG"]
segmentos_sin_censo = segmentos.loc[segmentos["CODSEG"].isin(segmentos_nan)].to_crs(epsg=4326)

centro = zonas_mapa.geometry.union_all().centroid
m = folium.Map(location=[centro.y, centro.x], zoom_start=9, tiles="OpenStreetMap")

folium.GeoJson(
    zonas_mapa,
    name="Zonas",
    style_function=lambda f: {
        "fillColor": "#e63946" if f["properties"]["sin_dato"] else "#d9d9d9",
        "color": "#666666",
        "weight": 0.8,
        "fillOpacity": 0.7,
    },
    highlight_function=lambda f: {"weight": 3, "color": "#000000"},
    tooltip=folium.GeoJsonTooltip(
        fields=["poligono_id", "tipo_zona", "poblacion"],
        aliases=["Polígono:", "Tipo de zona:", "Población:"],
        localize=True,
        sticky=True,
    ),
).add_to(m)

folium.GeoJson(
    segmentos_sin_censo[["CODSEG", "POB_TOT_23", "geometry"]],
    name="Segmentos sin match en el censo",
    style_function=lambda f: {
        "fillColor": "#2166ac",
        "color": "#2166ac",
        "weight": 1,
        "fillOpacity": 0.6,
    },
    tooltip=folium.GeoJsonTooltip(
        fields=["CODSEG", "POB_TOT_23"],
        aliases=["Segmento:", "POB_TOT_23:"],
        localize=True,
    ),
).add_to(m)

leyenda = """
<div style="position: fixed; bottom: 30px; left: 30px; z-index: 9999;
            background: white; padding: 12px 16px; border: 1px solid #999;
            border-radius: 4px; font-family: Arial; font-size: 13px;">
  <b>Zonas sin población calculada</b><br>
  <span style="color:#e63946;">&#9632;</span> Zona con NaN<br>
  <span style="color:#d9d9d9;">&#9632;</span> Zona con dato<br>
  <span style="color:#2166ac;">&#9632;</span> Segmento sin match en el censo
</div>
"""
m.get_root().html.add_child(folium.Element(leyenda))

folium.LayerControl(collapsed=False).add_to(m)
m

Zonas sin dato: 5 de 570


In [10]:
zonas_mapa = zonificacion.to_crs(epsg=4326).copy()

# Centro del mapa
centro = zonas_mapa.geometry.union_all().centroid

m = folium.Map(location=[centro.y, centro.x], zoom_start=9,tiles="OpenStreetMap")

# Escala de colores según población
poblacion_max = zonas_mapa["poblacion"].max()

colormap = cm.linear.YlOrRd_09.scale(0, poblacion_max)
colormap.caption = "Población estimada"

# Agregar zonas
folium.GeoJson(
    zonas_mapa,
    name="Zonas",
    style_function=lambda f: {
        "fillColor": (
            "#d9d9d9"
            if f["properties"]["poblacion"] is None
            else colormap(f["properties"]["poblacion"])
        ),
        "color": "#666666",
        "weight": 0.8,
        "fillOpacity": 0.8,
    },
    highlight_function=lambda f: {
        "weight": 3,
        "color": "#000000",
    },
    tooltip=folium.GeoJsonTooltip(
        fields=["poligono_id", "tipo_zona", "poblacion"],
        aliases=["Polígono:", "Tipo de zona:", "Población:"],
        localize=True,
        sticky=True,
    ),
).add_to(m)

colormap.add_to(m)

folium.LayerControl(collapsed=False).add_to(m)

m